In [1]:
import pandas as pd           
import numpy as np           
from sqlalchemy import create_engine
from sqlalchemy import text

#visualize
import plotly.express as px
import plotly.graph_objects as go
from plotly.subplots import make_subplots

print("Imported")


Imported


---
## Step 5: SQL Analysis

In [3]:
# Read Cleaned datasets 
df_acc_clean = pd.read_csv('D:/LendingClub/Datasets/accepted_sample_loans_clean.csv')
df_rej_clean = pd.read_csv('D:/LendingClub/Datasets/rejected_sample_loans_clean.csv')

In [ ]:
# MySQL Connection
DB_USER     = 'root'
DB_PASSWORD = '123456'
DB_HOST     = 'localhost'
DB_PORT     = 3306
DB_NAME     = 'lendingclub'

MySQL = f'mysql+pymysql://{DB_USER}:{DB_PASSWORD}@{DB_HOST}:{DB_PORT}/{DB_NAME}'
engine = create_engine(MySQL)
connection = engine.connect()


conn = engine.connect()
# Check if the connection is successful
conn.execute(text("SELECT 1"))
print("Connection to MySQL database was successful!")





Connection to MySQL database was successful!


In [ ]:
# Push the CLEAN data to the Accepted Loans database
df_acc_clean.to_sql('accepted_loans_clean', con=engine, if_exists='replace', index=False)
print(' - Clean dataset written to SQL table: accepted_loans_clean')

In [ ]:
# Push the CLEAN data to the Rejected Loans database
df_rej_clean.to_sql('rejected_loans_clean', con=engine, if_exists='replace', index=False)
print(' - Clean dataset written to SQL table: rejected_loans_clean')


In [ ]:
# run a SQL query and return a DataFrame
def run_sql(query):
    """Run a SQL query and return the result as a pandas DataFrame."""
    with engine.connect() as conn:
        return pd.read_sql(text(query), conn)

In [ ]:
# run a SQL query and return a DataFrame
def run_sql(query):
    """Run a SQL query and return the result as a pandas DataFrame."""
    with engine.connect() as conn:
        return pd.read_sql(text(query), conn)

### Business Question 1: What is the default rate by loan grade?

Grades go from A (safest) to G (riskiest).


In [ ]:
q1 = run_sql("""
SELECT
    grade,
    COUNT(*)            AS total_loans,
    SUM(target)         AS defaults,
    ROUND(SUM(target) * 100.0 / COUNT(*), 2)     AS default_rate_pct,
    ROUND(AVG(int_rate), 2)                      AS avg_interest_rate
FROM accepted_loans_clean
GROUP BY grade
ORDER BY grade;
""")

print('Default Rate by Loan Grade:')
print(q1.to_string(index=False))


Default Rate by Loan Grade:
grade  total_loans  defaults  default_rate_pct  avg_interest_rate
    A       235090   14201.0              6.04               7.11
    B       392741   52569.0             13.39              10.68
    C       381686   85649.0             22.44              14.02
    D       200953   61054.0             30.38              17.72
    E        93650   36035.0             38.48              21.14
    F        32058   14491.0             45.20              24.93
    G         9132    4560.0             49.93              27.73


### Business Question 2: Which loan purpose has the most defaults?


In [ ]:
q2 = run_sql("""
SELECT
    purpose,
    COUNT(*)                                          AS total_loans,
    SUM(target)                                       AS defaults,
    ROUND(SUM(target) * 100.0 / COUNT(*), 2)         AS default_rate_pct,
    ROUND(AVG(loan_amnt), 0)                          AS avg_loan_amount
FROM accepted_loans_clean
GROUP BY purpose
ORDER BY default_rate_pct DESC
""")

print('Default Rate by Loan Purpose:')
print(q2.to_string(index=False))


Default Rate by Loan Purpose:
           purpose  total_loans  defaults  default_rate_pct  avg_loan_amount
    small_business        15416    4580.0             29.71          15642.0
  renewable_energy          933     221.0             23.69          10018.0
            moving         9480    2214.0             23.35           7863.0
             house         7253    1587.0             21.88          15401.0
           medical        15554    3387.0             21.78           9000.0
debt_consolidation       780321  165014.0             21.15          15232.0
             other        77875   16385.0             21.04           9829.0
          vacation         9065    1738.0             19.17           6192.0
    major_purchase        29425    5473.0             18.60          11838.0
  home_improvement        87504   15502.0             17.72          14145.0
       educational          326      56.0             17.18           6796.0
       credit_card       295279   49982.0     

### Business Question 3: How do defaulters vs non-defaulters compare financially?


In [ ]:
q3 = run_sql("""
SELECT
    CASE WHEN target = 1 THEN 'Default' ELSE 'Fully Paid' END AS loan_outcome,
    COUNT(*)                          AS count,
    ROUND(AVG(loan_amnt),    0)       AS avg_loan_amount,
    ROUND(AVG(annual_inc),   0)       AS avg_annual_income,
    ROUND(AVG(int_rate),     2)       AS avg_interest_rate,
    ROUND(AVG(dti),          2)       AS avg_dti,
    ROUND(AVG(fico_range_low), 0)     AS avg_fico_score,
    ROUND(AVG(revol_util),   2)       AS avg_revolving_util_pct
FROM accepted_loans_clean
GROUP BY target
""")

print('Defaulters vs Non-Defaulters — Financial Profile Comparison:')
print(q3.to_string(index=False))


Defaulters vs Non-Defaulters — Financial Profile Comparison:
loan_outcome   count  avg_loan_amount  avg_annual_income  avg_interest_rate  avg_dti  avg_fico_score  avg_revolving_util_pct
  Fully Paid 1076751          14134.0            77706.0              12.62    17.81           698.0                   51.04
     Default  268559          15565.0            70401.0              15.71    20.17           688.0                   54.72


### Business Question 4: Default trend by year — is it getting better or worse?


In [ ]:
q4 = run_sql("""
SELECT
    issue_d,
    COUNT(*)                                          AS total_loans,
    SUM(target)                                       AS defaults,
    ROUND(SUM(target) * 100.0 / COUNT(*), 2)         AS default_rate_pct
FROM accepted_loans_clean
WHERE issue_d IS NOT NULL
GROUP BY issue_d
ORDER BY issue_d
""")

print('Default Rate by Issue Year:')
print(q4.to_string(index=False))


Default Rate by Issue Year:
 issue_d  total_loans  defaults  default_rate_pct
Apr-2008          155      27.0             17.42
Apr-2009          290      40.0             13.79
Apr-2010          827      82.0              9.92
Apr-2011         1563     222.0             14.20
Apr-2012         3230     496.0             15.36
Apr-2013         9419    1504.0             15.97
Apr-2014        18172    3320.0             18.27
Apr-2015        31785    6509.0             20.48
Apr-2016        24104    6173.0             25.61
Apr-2017        13103    3118.0             23.80
Apr-2018         6924    1362.0             19.67
Aug-2007           33       7.0             21.21
Aug-2008           71       6.0              8.45
Aug-2009          408      40.0              9.80
Aug-2010         1078     148.0             13.73
Aug-2011         1934     271.0             14.01
Aug-2012         5419     884.0             16.31
Aug-2013        12674    1941.0             15.31
Aug-2014        17730 

### Business Question 5: Accepted vs Rejected applicants — how do they differ?

This compares the two datasets to understand what separates approved from rejected borrowers.


In [ ]:
# First, also push rejected loans (clean version) to the DB
common_cols = ['loan_amnt', 'dti', 'fico_range_low']
available   = [c for c in common_cols if c in df_rej_clean.columns]

q5 = run_sql("""
SELECT 
    'Accepted' AS applicant_type,
    ROUND(AVG(loan_amnt), 0) AS avg_loan_requested,
    ROUND(AVG(dti), 2) AS avg_dti,
    ROUND(AVG(fico_range_low), 0) AS avg_fico_score
FROM 
    accepted_loans_clean

UNION ALL

SELECT 
    'Rejected' AS applicant_type,
    ROUND(AVG(loan_amnt), 0) AS avg_loan_requested,
    ROUND(AVG(dti), 2) AS avg_dti,
    ROUND(AVG(fico_range_low), 0) AS avg_fico_score
FROM 
    rejected_loans_clean
""")

print('Accepted vs Rejected Applicants — Average Profile:')
print(q5.to_string(index=False))
print()
print('Key Insight: Rejected applicants have lower income, lower FICO, and higher DTI.')


Accepted vs Rejected Applicants — Average Profile:
applicant_type  avg_loan_requested  avg_dti  avg_fico_score
      Accepted             14420.0    18.28           696.0
      Rejected             13105.0   143.43           634.0

Key Insight: Rejected applicants have lower income, lower FICO, and higher DTI.


### Business Question 6: High-risk segments — grade + purpose combination


In [ ]:
q6 = run_sql("""
SELECT
    grade,
    purpose,
    COUNT(*)                                  AS loans,
    ROUND(SUM(target)*100.0/COUNT(*), 1)      AS default_rate_pct
FROM accepted_loans_clean
GROUP BY grade, purpose
HAVING COUNT(*) >= 50
ORDER BY default_rate_pct DESC
LIMIT 10
""")

print('Top 10 Highest-Risk Grade + Purpose Combinations (min 50 loans):')
print(q6.to_string(index=False))


Top 10 Highest-Risk Grade + Purpose Combinations (min 50 loans):
grade            purpose  loans  default_rate_pct
    G debt_consolidation   5673              51.4
    G                car     53              50.9
    G     small_business    487              50.7
    G             moving    118              49.2
    G              other    985              48.8
    G        credit_card    627              48.2
    G            medical    109              47.7
    F     major_purchase    664              47.6
    G     major_purchase    196              47.4
    F debt_consolidation  20638              47.4



## Step 6: Exploratory Data Analysis (EDA)

Now we **visualize** the patterns we found with SQL.  
Good visualizations make it easier to spot what matters.


In [ ]:
counts = df_accepted['loan_status'].value_counts()
labels = ['Fully Paid', 'Charged Off']
colors = ['#2ecc71', '#e74c3c']

# Filter counts to only include the two labels we want
filtered_counts = counts[labels]

# Create subplots with plotly
fig = make_subplots(
    rows=1, cols=2,
    specs=[[{'type': 'bar'}, {'type': 'pie'}]],
    subplot_titles=('Count', 'Percentage')
)

# Bar chart (left subplot)
fig.add_trace(go.Bar(
    x=labels,
    y=filtered_counts.values,
    marker=dict(color=colors, line=dict(color='white', width=2)),
    name='Count',
    showlegend=False
), row=1, col=1)

# Add value labels on bars
for i, label in enumerate(labels):
    fig.add_annotation(
        x=label,
        y=filtered_counts.values[i],
        text=f'{filtered_counts.values[i]:,}',
        showarrow=False,
        yshift=10,
        font=dict(weight='bold'),
        row=1, col=1
    )

# Pie chart (right subplot)
fig.add_trace(go.Pie(
    labels=labels,
    values=filtered_counts.values,
    marker=dict(colors=colors, line=dict(color='white', width=2)),
    textinfo='label+percent'
), row=1, col=2)

fig.update_layout(
    title=dict(
        text='Question 1: How imbalanced is our target class?',
        font=dict(size=14),
        x=0.5,
        xanchor='center'
    ),
    height=500,
    width=1000,
    showlegend=False,
    template='plotly_white'
)

fig.update_xaxes(title_text='Loan Status', row=1, col=1)
fig.update_yaxes(title_text='Number of Loans', row=1, col=1)

fig.show()

default_rate = filtered_counts['Charged Off'] / filtered_counts.sum() * 100
print(f' Finding: Only {default_rate:.1f}% of loans defaulted — class is imbalanced.')
print(' We will handle this with SMOTE oversampling in the modeling step.')


 Finding: Only 20.0% of loans defaulted — class is imbalanced.
 We will handle this with SMOTE oversampling in the modeling step.


In [ ]:
df_grade_dist = df_acc_clean['grade'].value_counts().sort_index()

fig5 = px.bar(
    x=df_grade_dist.index,
    y=df_grade_dist.values,
    title='Grade Distribution',
    labels={'x': 'Grade', 'y': 'Number of loans'},
    color=df_grade_dist.index,
    color_discrete_sequence=px.colors.qualitative.Set2
)

fig5.update_layout(showlegend=False, height=600, width=900)
fig5.show()

In [ ]:
# Create the bar chart for default rate by grade
fig = go.Figure()

fig.add_trace(go.Bar(
    x=q1['grade'],
    y=q1['default_rate_pct'],
    marker_color=['#1a9641', '#a6d96a', '#ffffbf', '#fdae61', '#f46d43', '#d73027', '#a50026'],
    text=[f"{val}%" for val in q1['default_rate_pct']],
    textposition='outside',
    name='Default Rate (%)'
))

# Add the line chart for average interest rate
fig.add_trace(go.Scatter(
    x=q1['grade'],
    y=q1['avg_interest_rate'],
    mode='lines+markers',
    line=dict(color="#0460bb", width=2, dash='dash'),
    marker=dict(size=8),
    name='Avg Interest Rate (%)'
))

# Update layout for the chart
fig.update_layout(
    title='Default Rate & Average Interest Rate by Loan Grade',
    xaxis_title='Loan Grade',
    yaxis=dict(title='Default Rate (%)', side='left'),
    yaxis2=dict(title='Avg Interest Rate (%)', overlaying='y', side='right'),
    legend=dict(x=0.8, y=1.2),
    template='plotly_white'
)

# Show the chart
fig.show()

print('Key Insight: Default rate increases sharply from grade A to G.')
print('Grade G loans default at ~5x the rate of grade A loans.')

Key Insight: Default rate increases sharply from grade A to G.
Grade G loans default at ~5x the rate of grade A loans.


In [ ]:
# Create target variable
# 0 = Fully Paid
# 1 = Charged Off (Default)

df_acc_clean["target"] = (
    df_acc_clean["loan_status"] == "Charged Off"
).astype(int)

print(df_acc_clean["target"].value_counts())

target
0    1076751
1     268559
Name: count, dtype: int64


In [ ]:
# Convert important columns to numbers

numeric_cols = [
    "int_rate",
    "annual_inc",
    "dti",
    "fico_range_low",
    "loan_amnt",
    "revol_util"
]

for col in numeric_cols:
    df_acc_clean[col] = pd.to_numeric(
        df_acc_clean[col],
        errors="coerce"
    )

print("Numeric columns converted successfully.")

Numeric columns converted successfully.


In [ ]:
import plotly.express as px

fig = px.histogram(
    df_acc_clean,
    x="int_rate",
    color="target",
    nbins=30,
    histnorm="probability",
    barmode="overlay",
    opacity=0.6,
    color_discrete_map={0: "#2ecc71", 1: "#e74c3c"},
    labels={
        "int_rate": "Interest Rate (%)",
        "target": "Loan Status"
    },
    title="Interest Rate Distribution"
)

fig.update_layout(
    template="plotly_white"
)

fig.show()

In [ ]:
income_plot = df_acc_clean[
    df_acc_clean["annual_inc"] <
    df_acc_clean["annual_inc"].quantile(0.95)
]

fig = px.histogram(
    income_plot,
    x="annual_inc",
    color="target",
    nbins=30,
    histnorm="probability",
    barmode="overlay",
    opacity=0.6,
    color_discrete_map={0: "#2ecc71", 1: "#e74c3c"},
    labels={
        "annual_inc": "Annual Income ($)",
        "target": "Loan Status"
    },
    title="Annual Income Distribution"
)

fig.update_layout(
    template="plotly_white"
)

fig.show()

In [ ]:
fig = px.histogram(
    df_acc_clean,
    x="dti",
    color="target",
    nbins=30,
    histnorm="probability",
    barmode="overlay",
    opacity=0.6,
    color_discrete_map={0: "#2ecc71", 1: "#e74c3c"},
    labels={
        "dti": "Debt-to-Income Ratio",
        "target": "Loan Status"
    },
    title="Debt-to-Income Ratio Distribution"
)

fig.update_layout(
    template="plotly_white"
)

fig.show()

In [ ]:
fig = px.histogram(
    df_acc_clean,
    x="fico_range_low",
    color="target",
    nbins=30,
    histnorm="probability",
    barmode="overlay",
    opacity=0.6,
    color_discrete_map={0: "#2ecc71", 1: "#e74c3c"},
    labels={
        "fico_range_low": "FICO Score",
        "target": "Loan Status"
    },
    title="FICO Score Distribution"
)

fig.update_layout(
    template="plotly_white"
)

fig.show()

In [ ]:
fig = px.histogram(
    df_acc_clean,
    x="loan_amnt",
    color="target",
    nbins=30,
    histnorm="probability",
    barmode="overlay",
    opacity=0.6,
    color_discrete_map={0: "#2ecc71", 1: "#e74c3c"},
    labels={
        "loan_amnt": "Loan Amount ($)",
        "target": "Loan Status"
    },
    title="Loan Amount Distribution"
)

fig.update_layout(
    template="plotly_white"
)

fig.show()

In [ ]:
fig = px.histogram(
    df_acc_clean,
    x="revol_util",
    color="target",
    nbins=30,
    histnorm="probability",
    barmode="overlay",
    opacity=0.6,
    color_discrete_map={0: "#2ecc71", 1: "#e74c3c"},
    labels={
        "revol_util": "Revolving Utilization (%)",
        "target": "Loan Status"
    },
    title="Revolving Utilization Distribution"
)

fig.update_layout(
    template="plotly_white"
)

fig.show()

In [ ]:
import plotly.express as px
fig = px.histogram(
    df_acc_clean,
    x="fico_range_low",
    nbins=30,
    histnorm="probability",
    barmode="overlay",
    opacity=0.6,
    labels={
        "fico_range_low": "FICO Score",
        "loan_result": "Loan Status"
    },
    title="FICO Score Distribution: Fully Paid vs Default"
)

fig.update_layout(
    template="plotly_white"
)

fig.show()

In [ ]:
# Sort the data by default rate percentage
q2_sorted = q2.sort_values('default_rate_pct', ascending=True)

# Create the horizontal bar chart
fig = go.Figure()

fig.add_trace(go.Bar(
    x=q2_sorted['default_rate_pct'],
    y=q2_sorted['purpose'],
    orientation='h',
    marker=dict(
        color=q2_sorted['default_rate_pct'],
        colorscale='RdYlGn_r',  # Reverse Red-Yellow-Green colormap
        showscale=True
    ),
    text=[f"{val}%" for val in q2_sorted['default_rate_pct']],
    textposition='outside',
    name='Default Rate (%)'
))

# Update layout for the chart
fig.update_layout(
    title='Default Rate by Loan Purpose',
    xaxis_title='Default Rate (%)',
    yaxis_title='Loan Purpose',
    template='plotly_white',
    height=600,
    width=800
)

# Show the chart
fig.show()

In [ ]:
# Compute the correlation matrix
numeric_features = ['loan_amnt', 'int_rate', 'installment', 'annual_inc',
                    'dti', 'fico_range_low', 'open_acc', 'pub_rec', 'revol_util',
                    'emp_length', 'term', 'target']
numeric_features = [c for c in numeric_features if c in df_acc_clean.columns]
corr_matrix = df_acc_clean[numeric_features].corr()

# Mask the upper triangle
mask = np.triu(np.ones_like(corr_matrix, dtype=bool))

# Convert the correlation matrix to a long format for Plotly
corr_long = corr_matrix.mask(mask).stack().reset_index()
corr_long.columns = ['Feature 1', 'Feature 2', 'Correlation']

# Create the heatmap
fig = px.imshow(
    corr_matrix,
    x=corr_matrix.columns,
    y=corr_matrix.columns,
    color_continuous_scale='RdBu',  # Use a valid Plotly colorscale
    zmin=-1,
    zmax=1,
    title='Step 6.3 — Feature Correlation Heatmap (focus on the "target" row)'
)

# Update layout for better readability
fig.update_layout(
    width=800,
    height=800,
    coloraxis_colorbar=dict(title='Correlation'),
    xaxis=dict(tickangle=45),
    template='plotly_white'
)

# Show the heatmap
fig.show()

# Print the features most correlated with the target
target_corr = corr_matrix['target'].drop('target').sort_values(key=abs, ascending=False)
print('\nFeatures most correlated with default (target):')
for feat, corr in target_corr.head(8).items():
    direction = '↑ higher = more defaults' if corr > 0 else '↓ higher = fewer defaults'
    print(f'  {feat:<20} : {corr:+.3f}  ({direction})')


Features most correlated with default (target):
  int_rate             : +0.259  (↑ higher = more defaults)
  term                 : +0.176  (↑ higher = more defaults)
  fico_range_low       : -0.131  (↓ higher = fewer defaults)
  dti                  : +0.084  (↑ higher = more defaults)
  loan_amnt            : +0.066  (↑ higher = more defaults)
  revol_util           : +0.060  (↑ higher = more defaults)
  installment          : +0.052  (↑ higher = more defaults)
  annual_inc           : -0.042  (↓ higher = fewer defaults)



## Step 7: Feature Engineering

Feature engineering means **creating new columns** that help the model learn better patterns.  
We use domain knowledge about lending to build meaningful features.


In [ ]:
df_acc_clean.head()

,loan_amnt,term,int_rate,installment,grade,emp_length,home_ownership,annual_inc,purpose,dti,fico_range_low,open_acc,pub_rec,revol_util,loan_status,issue_d,target
0,3600.0,36.0,13.99,123.03,C,10.0,MORTGAGE,55000.0,debt_consolidation,5.91,675.0,7.0,0.0,29.7,Fully Paid,Dec-2015,0
1,24700.0,36.0,11.99,820.28,C,10.0,MORTGAGE,65000.0,small_business,16.06,715.0,22.0,0.0,19.2,Fully Paid,Dec-2015,0
2,20000.0,60.0,10.78,432.66,B,10.0,MORTGAGE,63000.0,home_improvement,10.78,695.0,6.0,0.0,56.2,Fully Paid,Dec-2015,0
3,10400.0,60.0,22.45,289.91,F,3.0,MORTGAGE,104433.0,major_purchase,25.37,695.0,12.0,0.0,64.5,Fully Paid,Dec-2015,0
4,11950.0,36.0,13.44,405.18,C,4.0,RENT,34000.0,debt_consolidation,10.20,690.0,5.0,0.0,68.4,Fully Paid,Dec-2015,0


In [ ]:
# Create the target column
df_acc_clean["target"] = df_acc_clean["loan_status"].map({
    "Fully Paid": 0,
    "Charged Off": 1
}).astype(int)

print('Target Column Created')

Target Column Created


In [ ]:
#Create new features

df_acc_feat = df_acc_clean.copy()

# Ensure numeric columns are properly converted
numeric_columns = ['installment', 'annual_inc', 'loan_amnt', 'term', 'pub_rec']
for col in numeric_columns:
    df_acc_feat[col] = pd.to_numeric(df_acc_feat[col], errors='coerce')

# Monthly payment as percentage of income
df_acc_feat['payment_to_income'] = df_acc_feat['installment'] / (df_acc_feat['annual_inc'] / 12 + 1)

# Loan amount relative to annual income
df_acc_feat['loan_to_income'] = df_acc_feat['loan_amnt'] / (df_acc_feat['annual_inc'] + 1)

# Interest burden — total interest cost of the loan
df_acc_feat['total_interest'] = (df_acc_feat['installment'] * df_acc_feat['term']) - df_acc_feat['loan_amnt']

# Public records flag — did this person ever have a bankruptcy?
df_acc_feat['has_pub_rec'] = (df_acc_feat['pub_rec'] > 0).astype(int)

# Grade encoded as a number (A=0, B=1, ..., G=6)
grade_mapping = {g: i for i, g in enumerate(['A', 'B', 'C', 'D', 'E', 'F', 'G'])}
df_acc_feat['grade_num'] = df_acc_feat['grade'].map(grade_mapping)

new_features = ['payment_to_income', 'loan_to_income', 'total_interest', 'has_pub_rec', 'grade_num']
print(f"New features created: {', '.join(new_features)}")
print(f"Dataset now has {df_acc_feat.shape[1]} columns")

New features created: payment_to_income, loan_to_income, total_interest, has_pub_rec, grade_num
Dataset now has 22 columns


In [ ]:
#accepted loans cleaned dataset with new features
df_acc_feat.to_csv('D:/LendingClub/Datasets/sample_of_accepted_loans_clean_with_features.csv', index=False)